# TBI mouse K-Fold

Original D1 train/test animal assignments are preserved. MouseFull adds balanced D3 holdouts; rats keep all longitudinal scans of each animal together.

`USE_VALIDATION_FOR_SELECTION=False` trains the complete epoch budget without validation passes, uses a preset cosine learning-rate schedule, and evaluates the last epoch. Test animals are evaluated only after fitting.

Set it to `True` to reserve separate inner validation from the training pool and use ReduceLROnPlateau plus validation-selected weights. It never uses test animals for checkpoint selection. Start a fresh run when changing this policy.


In [1]:
from pathlib import Path
import sys

REPO_ROOT: Path = next(
    path for path in (Path.cwd(), *Path.cwd().parents)
    if (path / "src/experiments/config.py").is_file()
)
if str(REPO_ROOT) not in sys.path:
    sys.path.insert(0, str(REPO_ROOT))

from src.experiments.training import configure_runtime

TRAINING_SEED: int = 42
runtime = configure_runtime(seed=TRAINING_SEED, memory_growth=True, mixed_precision=False)
runtime
import nibabel as nib

REFERENCE: Path = (
    REPO_ROOT / "example" / "RARE" / "TBI_fm_19_49"
    / "Anat" / "TBI_fm_19_49_N4.nii.gz"
)
ref_img = nib.load(REFERENCE)
reference_axes = nib.aff2axcodes(ref_img.affine)
print("Reference axes:", reference_axes, "(left-right is the R/L axis)")


Reference axes: ('R', 'I', 'A') (left-right is the R/L axis)


## Complete D1 configuration

This notebook owns the TBI mouse settings. Rat and MouseFull experiments have separate notebooks. Augmentation and scan repetition apply only to training. Extra D1 anatomy is explicitly mapped to background for this four-class task. To resume, set `RESUME_RUN` and retain the saved configuration and input data.

Full-volume outputs use `original_label_ids=True`. `postprocessing_settings` controls brain-mask cleanup and ventricle separation. Thresholds are voxel counts on the 0.1 mm grid; categorical ROI masks are not cleaned as binary masks. Merged D1/rat ventricles are separated before mapping to original IDs 3 (contra), 13 (ipsi), and 21 (third ventricle). MouseFull keeps its directly predicted sides. GT uses the selected original annotations, never the prediction postprocessor.

The historical `default_hemisphere="right"` selects the plane side containing array origin, rather than deriving anatomical right from the affine. It is used when no sufficiently large lesion is predicted. Splitting requires at least three predicted third-ventricle voxels; missing midline predictions raise an explicit scan-specific error.


In [ ]:
from src.experiments.config import (
    DataConfig, DatasetSpec, EvaluationPatchConfig, ExperimentConfig, InferenceConfig, InitializationConfig,
    LabelConfig, LossConfig, ModelConfig, PostprocessingConfig, PreprocessingConfig,
)
from src.evaluation.k_fold import EvaluationConfig, TrainingConfig

DATA_ROOT: Path = Path("D:/Other files/TESI_CNN/MANUSCRIPT_DATASET/normalized")
REFERENCE_SPLITS: Path | None = DATA_ROOT.parent / "D1_splits_final.json"
REFERENCE_FOLD: int = 4  # Fixed studies reuse this fold; CV uses all reference folds.
RUN_TRAINING: bool = True
RESUME_RUN: Path | None = None
FOLD_FILE: Path | None = None
COHORT_SPLIT_FILE: Path | None = None
EPOCHS: int = 100

# False: no validation pass, preset LR schedule, final epoch for evaluation.
USE_VALIDATION_FOR_SELECTION: bool = False
INITIAL_LEARNING_RATE: float = 0.001
MINIMUM_LEARNING_RATE: float = 1e-7

fixed_epoch_training: bool = not USE_VALIDATION_FOR_SELECTION
checkpoint_monitor: str = "loss"
if USE_VALIDATION_FOR_SELECTION:
    checkpoint_monitor = "val_loss"

training = TrainingConfig(
    model_name="d1_3drnet_kfold", k=5, epochs=EPOCHS, batch_size=8,
    seed=TRAINING_SEED, data_multiplier=3, output_dir=str(REPO_ROOT / "results"),
    monitor=checkpoint_monitor, monitor_mode="min", fixed_epochs=fixed_epoch_training, default_callbacks=False,
    fit_kwargs={"verbose": 1},
)
data_settings = DataConfig(root=DATA_ROOT, datasets=(DatasetSpec(name="D1", annotation_scope="full_volume"),))
preprocessing = PreprocessingConfig(
    reference=REFERENCE, patch_size=(80, 80, 80), spacing_mm=(0.1, 0.1, 0.1),
    correct_units=True, augment=True, random_crop=True, crop_mode="center",
    # Native-grid MRI degradation; bounds retain their earlier magnitudes.
    intensity_augmentation_grid="native",
    blur_sigma_range=(0.0, 0.6), blur_sigma_units="voxels",
    noise_std_range=(0.0, 0.05), noise_std_units="intensity",
    flip_probability=0.5,
)
# Sample once; validation/test reuse evaluation_patches.json across epochs and runs.
evaluation_patch_settings = EvaluationPatchConfig(
    patches_per_scan=3, sampling="center_biased", seed=42,
    left_right_pairs=False,  # D1/rats: optional paired LR views; MouseFull: keep False.
)

model_settings = ModelConfig(
    architecture="3drnet", filters=(16, 32, 64, 128, 256),
    residual=True, attention=True, max_pooling=True, classifier=False,
)
loss_settings = LossConfig(
    regions="dice_ce", gamma=0.8, brain_alpha=0.6, batch_wise=True,
    # Total loss = weighted sum of the active output-head losses.
    regions_weight=1.0, brain_weight=1.0, classifier_weight=1.0,
)
# Full volumes: postprocess first, then restore original annotation IDs.
postprocessing_settings = PostprocessingConfig(
    clean_brain_mask=True,
    fill_small_holes=True, holes_max_area=20000,
    remove_small_objects=True, object_min_area=30000,
    split_ventricles=True, use_centroids=True,
    default_hemisphere="right", lesion_voxels_threshold=10,
)
inference_settings = InferenceConfig(
    enabled=True, stride=40, save_predictions=True,
    original_label_ids=True, postprocessing=postprocessing_settings,
)
initialization = InitializationConfig()

config = ExperimentConfig(
    data=data_settings, preprocessing=preprocessing, training=training,
    evaluation_patches=evaluation_patch_settings,
    model=model_settings, labels=LabelConfig(unknown="background"), loss=loss_settings,
    inference=inference_settings, initialization=initialization, learning_rate=INITIAL_LEARNING_RATE,
    split_seed=42, cv_validation_fraction=0.2,
)
config.validate()

## Configure callbacks directly

Default two-way CV uses a cosine learning-rate schedule and final-epoch weights. `USE_VALIDATION_FOR_SELECTION=True` enables separate inner validation, ReduceLROnPlateau and best-validation weights. The actual callback instances are visible and editable in the next cell.


In [3]:
import tensorflow as tf
from src.experiments.schedules import CosineEpochSchedule

# Select the policy explicitly; test/holdout metrics never drive these callbacks.
callbacks: list[tf.keras.callbacks.Callback] = []
if USE_VALIDATION_FOR_SELECTION:
    reduce_lr = tf.keras.callbacks.ReduceLROnPlateau(
        monitor="val_loss", mode="min", factor=0.5, patience=10,
        min_lr=MINIMUM_LEARNING_RATE, verbose=1,
    )
    callbacks.append(reduce_lr)
else:
    schedule = CosineEpochSchedule(
        initial_learning_rate=config.learning_rate,
        minimum_learning_rate=MINIMUM_LEARNING_RATE,
        epochs=config.training.epochs,
    )
    scheduler = tf.keras.callbacks.LearningRateScheduler(schedule=schedule, verbose=1)
    callbacks.append(scheduler)

csv_filename: str = "training.csv"
csv_logger = tf.keras.callbacks.CSVLogger(filename=csv_filename, append=True)
callbacks.append(csv_logger)


## Animal splits

Load `FOLD_FILE` for matched comparisons, or generate deterministic outer folds. Optional `COHORT_SPLIT_FILE` reserves the fixed-split run's test animals; repeated test predictions across fold models are not additional biological samples. Confirmed duplicate animals may be grouped through `DataConfig.animal_ids`.

The default `REFERENCE_SPLITS` is `DATA_ROOT.parent / "D1_splits_final.json"`.
The reference stores the original `train` and `test` animal lists.
Original D1 memberships are preserved without modality rebalancing;
optional inner validation comes only from training. Superseded files are backed up.
Fixed runs use `REFERENCE_FOLD=4`; K-Fold runs use the complete reference plan.
MouseFull adds balanced SHAM folds while preserving every updated D1 role.
Explicit `SPLIT_FILE`/`FOLD_FILE` and resumed memberships take precedence.
Set `REFERENCE_SPLITS=None` to generate a fresh plan. Mouse experiments start
from scratch on these memberships; weights are not shared across folds.


In [4]:
from IPython.display import display
from src.experiments.data import SubjectSplit, fold_summary, make_pretrained_cv_splits, prepare_data
from src.evaluation.k_fold import load_fold_splits

prepared = prepare_data(config)
cv_ids = prepared.subjects.subject_ids
test_ids: tuple[str, ...] = ()

if COHORT_SPLIT_FILE is not None:
    cohort = SubjectSplit.load(COHORT_SPLIT_FILE, prepared.subjects)
    cv_ids = sorted((*cohort.train, *cohort.validation))
    test_ids = cohort.test

evaluation = EvaluationConfig(
    test_ids=test_ids, evaluate_validation=USE_VALIDATION_FOR_SELECTION,
    save_predictions=config.inference.save_predictions,
)

if RESUME_RUN is not None:
    split_path = RESUME_RUN / "splits.json"
    folds = load_fold_splits(split_path, cv_ids, config.training.k)
    if FOLD_FILE is not None:
        requested_folds = load_fold_splits(FOLD_FILE, cv_ids, config.training.k)
        if requested_folds != folds:
            raise ValueError("FOLD_FILE differs from the resumed run's folds")
elif FOLD_FILE is not None:
    folds = load_fold_splits(FOLD_FILE, cv_ids, config.training.k)
else:
    folds = make_pretrained_cv_splits(
        data=prepared, subject_ids=cv_ids, reference_file=REFERENCE_SPLITS,
    )

if any(not fold.test_ids for fold in folds):
    raise ValueError("Mouse K-Fold requires independent outer holdout animals")

summary = fold_summary(folds, prepared.subjects)
manifest = prepared.subjects.manifest(cv_ids)
display(summary)
display(manifest.head())
print("Separate test animals:", len(test_ids))

,Fold,Role,Animals,Scans
0,0,train,71,71
1,0,validation,18,18
2,0,holdout,23,23
3,1,train,71,71
4,1,validation,18,18
5,1,holdout,23,23
6,2,train,72,72
7,2,validation,18,18
8,2,holdout,22,22
9,3,train,72,72


,Subject,Group,Scan,Dataset,SubjectID,OriginalID,Timepoint,Subgroup,Condition,Species,Strain,Protocol,Modality,ImagePath
0,D1/SUBJ_0001,D1_T1w,SUBJ_0001,D1,SUBJ_0001,Isch_PAL_PPIAKO_1767,None,G1-TBI-T1w-c52-4-labels,TBI,mouse,unknown,c52,T1w,D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\nor...
1,D1/SUBJ_0002,D1_T1w,SUBJ_0002,D1,SUBJ_0002,Isch_PAL_PPIAKO_1777,None,G1-TBI-T1w-c52-4-labels,TBI,mouse,unknown,c52,T1w,D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\nor...
2,D1/SUBJ_0003,D1_T1w,SUBJ_0003,D1,SUBJ_0003,Isch_PAL_PPIAKO_1781,None,G1-TBI-T1w-c52-4-labels,TBI,mouse,unknown,c52,T1w,D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\nor...
3,D1/SUBJ_0004,D1_T1w,SUBJ_0004,D1,SUBJ_0004,Isch_PAL_PPIAKO_1782,None,G1-TBI-T1w-c52-4-labels,TBI,mouse,unknown,c52,T1w,D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\nor...
4,D1/SUBJ_0005,D1_T1w,SUBJ_0005,D1,SUBJ_0005,Isch_PAL_PPIAKO_1783,None,G1-TBI-T1w-c52-4-labels,TBI,mouse,unknown,c52,T1w,D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\nor...


Separate test animals: 0


## Check one validation batch

This checks the shared preprocessing and target shapes without building a model. Validation keeps its final incomplete batch and all selected timepoints.

In [5]:
validation_ids = folds[0].val_ids
validation_generator = prepared.make_generator(validation_ids, training=False, batch_size=1)
images, targets = validation_generator[0]

print("Input:", images.shape)
print("ROI targets:", targets[0].shape)
print("Brain targets:", targets[1].shape)
print("Validation batches:", len(validation_generator))

del images, targets, validation_generator

Generator configuration:
- Dataset path: D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\normalized
- Dimensions: (80, 80, 80)
- Batch size: 1
- Number of input channels: 1
- Number of classes: 4
- Shuffle: False

Input: (1, 80, 80, 80, 1)
ROI targets: (1, 80, 80, 80, 4)
Brain targets: (1, 80, 80, 80, 1)
Validation batches: 54


## Train or resume

Each fold restores its best validation-selected weights before full-volume evaluation. Metrics use physical spacing; saved masks return to each input scan's original geometry and contain original annotation IDs. Configuration, annotation policy, animal manifests, splits and initialization audits are saved alongside recovery state.

In [6]:
from src.experiments.training import run_cross_validation

result = None
if RUN_TRAINING:
    result = run_cross_validation(
        prepared, subject_ids=cv_ids, folds=folds,
        evaluation=evaluation, resume_run=RESUME_RUN, callbacks=callbacks,
    )
    print("Run saved to:", result.run_dir)
else:
    print("Checks complete. Set RUN_TRAINING = True to train or resume.")

Generator configuration:
- Dataset path: D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\normalized
- Dimensions: (80, 80, 80)
- Batch size: 8
- Number of input channels: 1
- Number of classes: 4
- Shuffle: True

Generator configuration:
- Dataset path: D:\Other files\TESI_CNN\MANUSCRIPT_DATASET\normalized
- Dimensions: (80, 80, 80)
- Batch size: 8
- Number of input channels: 1
- Number of classes: 4
- Shuffle: False

Training checkpoints: c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3drnet_kfold\RUN_20261015_130622_443191\fold_0
Epoch 1/10
27/27 [==============================] - 467s 13s/step - loss: 0.4425 - regions_loss: 0.2078 - brain_mask_loss: 0.1526 - regions_mean_dice: 0.1195 - brain_mask_mean_dice: 0.8656 - val_loss: 3.8707 - val_regions_loss: 2.3682 - val_brain_mask_loss: 1.4211 - val_regions_mean_dice: 0.0187 - val_brain_mask_mean_dice: 0.5705 - lr: 0.0010
Epoch 2/10
27/27 [==============================] - 285s 11s/step - loss: 0.3029 - regions_loss: 0.1342 - brain_mask_loss: 0.

## Independent outer results

Plotly uses the native VS Code renderer. The table below selects `DatasetRole="holdout"`. Keep scans grouped by animal for later statistical comparisons.

In [7]:
import pandas as pd
import plotly.io as pio
from src.experiments.training import history_figure

pio.renderers.default = "vscode"

if result is not None:
    figure = history_figure(result)
    figure.show()
    display(pd.DataFrame(result.timings))

    if result.evaluations.get("regions"):
        metrics = pd.concat(result.evaluations["regions"], ignore_index=True)
        evaluated = metrics.loc[metrics["DatasetRole"] == "holdout"]
        dice = evaluated.loc[evaluated["Metric"] == "Dice"]
        columns = ["Fold", "Subject", "Scan", "Region", "Value", "Status"]
        display(dice[columns])
        print("Full metric tables:", result.run_dir / "regions")

,fold,training_seconds,evaluation_seconds,epochs_completed,parameter_count,best_epoch
0,0,3084.014069,473.781249,10,7173518,9
1,1,2789.334761,730.510086,10,7173518,8
2,2,2996.132427,722.720434,10,7173518,7
3,3,2775.979130,855.254997,10,7173518,9
4,4,3112.675930,684.464270,10,7173518,9


,Fold,Subject,Scan,Region,Value,Status
900,0,D1/SUBJ_0001,SUBJ_0001,Lesion,0.884247,ok
910,0,D1/SUBJ_0001,SUBJ_0001,Contra ventricle,0.413968,ok
920,0,D1/SUBJ_0001,SUBJ_0001,Ipsi ventricle,0.418317,ok
930,0,D1/SUBJ_0001,SUBJ_0001,Third ventricle,0.647912,ok
940,0,D1/SUBJ_0001,SUBJ_0001,Brain,0.979799,ok
...,...,...,...,...,...,...
10050,4,D1/SUBJ_0112,SUBJ_0112,Lesion,0.487026,ok
10060,4,D1/SUBJ_0112,SUBJ_0112,Contra ventricle,0.000531,ok
10070,4,D1/SUBJ_0112,SUBJ_0112,Ipsi ventricle,0.258529,ok
10080,4,D1/SUBJ_0112,SUBJ_0112,Third ventricle,0.261856,ok


Full metric tables: c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3drnet_kfold\RUN_20261015_130622_443191\regions


## Best-checkpoint patch and full-volume measurements

Native patch losses and metrics use every saved deterministic validation/test patch. These are cohort aggregates, not independent animal scores. Full-volume brain and region scores use postprocessed predictions, original annotation IDs and valid references. The workbook contains separate sheets for the two evaluation stages.


In [8]:
import pandas as pd

if result is not None:
    display(result.patch_metrics)
    volume_tables = [table for tables in result.evaluations.values() for table in tables]
    full_volume_metrics = pd.DataFrame()
    if volume_tables:
        full_volume_metrics = pd.concat(volume_tables, ignore_index=True)
    evaluation_folder = result.run_dir / "summary"
    selected_columns = ["DatasetRole", "Fold", "Head", "Region", "Metric", "Value", "Status"]
    if not full_volume_metrics.empty:
        display(full_volume_metrics[selected_columns].head(30))
    from src.evaluation.classification import classification_report, healthy_lesion_report
    classifier_report_result = classification_report(result.classifier_predictions)
    if not classifier_report_result.summary.empty:
        display(classifier_report_result.summary)
        display(classifier_report_result.confusion)
    sham_animals, sham_summary = healthy_lesion_report(full_volume_metrics)
    if not sham_summary.empty:
        display(sham_summary)
    from src.evaluation.reporting import evaluation_report

    report_manifest = prepared.subjects.manifest(prepared.subjects.subject_ids)
    detailed_report = evaluation_report(full_volume_metrics, manifest=report_manifest)
    display(detailed_report.region_set_summary)
    display(detailed_report.region_coverage)
    display(detailed_report.subgroup_summary)
    print("Additional anatomy, cohort, participant and structure-size tables are in the workbook.")
    print("Complete native patch and postprocessed volume tables:", evaluation_folder)
    print("Workbook:", evaluation_folder / "evaluation_metrics.xlsx")
else:
    print("Use the final best-checkpoint cell to evaluate a stopped or saved run.")


,Subject,Scan,Dataset,EvaluationStage,Aggregation,AnimalCount,ScanCount,PatchCount,Unit,Head,...,Metric,Value,Status,Fold,DatasetRole,Seed,BestEpoch,ModelVariant,ExperimentName,RunID
0,,,D1,patch,cohort_pooled,18,18,54,unitless,total,...,loss,0.161659,ok,0,validation,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
1,,,D1,patch,cohort_pooled,18,18,54,unitless,regions,...,regions_loss,0.065469,ok,0,validation,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
2,,,D1,patch,cohort_pooled,18,18,54,unitless,brain_mask,...,brain_mask_loss,0.027123,ok,0,validation,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
3,,,D1,patch,cohort_pooled,18,18,54,unitless,regions,...,regions_mean_dice,0.628610,ok,0,validation,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
4,,,D1,patch,cohort_pooled,18,18,54,unitless,brain_mask,...,brain_mask_mean_dice,0.976373,ok,0,validation,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
5,,,D1,patch,cohort_pooled,23,23,69,unitless,total,...,loss,0.165483,ok,0,holdout,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
6,,,D1,patch,cohort_pooled,23,23,69,unitless,regions,...,regions_loss,0.070003,ok,0,holdout,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
7,,,D1,patch,cohort_pooled,23,23,69,unitless,brain_mask,...,brain_mask_loss,0.026413,ok,0,holdout,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
8,,,D1,patch,cohort_pooled,23,23,69,unitless,regions,...,regions_mean_dice,0.604462,ok,0,holdout,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191
9,,,D1,patch,cohort_pooled,23,23,69,unitless,brain_mask,...,brain_mask_mean_dice,0.977782,ok,0,holdout,42,10,3drnet,d1_3drnet_kfold,RUN_20261015_130622_443191


,DatasetRole,Fold,Head,Region,Metric,Value,Status
0,validation,0,regions,Lesion,Dice,0.845311,ok
1,validation,0,regions,Lesion,IoU,0.732068,ok
2,validation,0,regions,Lesion,HD95,0.458260,ok
3,validation,0,regions,Lesion,ASSD,0.144332,ok
4,validation,0,regions,Lesion,AVE,4.351000,ok
5,validation,0,regions,Lesion,RVE,18.510955,ok
6,validation,0,regions,Lesion,Sensitivity,0.923548,ok
7,validation,0,regions,Lesion,Precision,0.779294,ok
8,validation,0,regions,Lesion,ReferenceVolume,23.505000,ok
9,validation,0,regions,Lesion,PredictionVolume,27.856000,ok


,Variant,DatasetRole,Dataset,Condition,RegionSet,Metric,Unit,Animals,Scans,Mean,SD,Minimum,Maximum
0,3drnet,holdout,D1,TBI,all_roi,ASSD,mm,112,112,0.661395,1.108680,0.071188,6.426773
1,3drnet,holdout,D1,TBI,all_roi,AVE,mm3,112,112,3.793277,8.321232,0.212250,49.240250
2,3drnet,holdout,D1,TBI,all_roi,Dice,fraction,112,112,0.544551,0.135219,0.206406,0.811811
3,3drnet,holdout,D1,TBI,all_roi,HD95,mm,112,112,3.620231,6.940138,0.224766,32.742059
4,3drnet,holdout,D1,TBI,all_roi,IoU,fraction,112,112,0.412913,0.120812,0.127755,0.686100
...,...,...,...,...,...,...,...,...,...,...,...,...,...
59,3drnet,validation,D1,TBI,anatomy_only,HD95,mm,68,68,4.268137,7.677933,0.213275,37.414169
60,3drnet,validation,D1,TBI,anatomy_only,IoU,fraction,68,68,0.331700,0.141612,0.041256,0.659047
61,3drnet,validation,D1,TBI,anatomy_only,Precision,fraction,68,68,0.672077,0.221571,0.107052,0.989899
62,3drnet,validation,D1,TBI,anatomy_only,RVE,%,68,68,-21.224740,50.699587,-95.807715,135.267065


,Variant,DatasetRole,Dataset,Condition,Head,Region,Metric,Unit,Status,Animals,Measurements,Finite
0,3drnet,holdout,D1,TBI,brain_mask,Brain,ASSD,mm,ok,112,112,112
1,3drnet,holdout,D1,TBI,brain_mask,Brain,AVE,mm3,ok,112,112,112
2,3drnet,holdout,D1,TBI,brain_mask,Brain,Dice,fraction,ok,112,112,112
3,3drnet,holdout,D1,TBI,brain_mask,Brain,HD95,mm,ok,112,112,112
4,3drnet,holdout,D1,TBI,brain_mask,Brain,IoU,fraction,ok,112,112,112
...,...,...,...,...,...,...,...,...,...,...,...,...
145,3drnet,validation,D1,TBI,regions,Third ventricle,Precision,fraction,ok,68,90,90
146,3drnet,validation,D1,TBI,regions,Third ventricle,PredictionVolume,mm3,ok,68,90,90
147,3drnet,validation,D1,TBI,regions,Third ventricle,RVE,%,ok,68,90,90
148,3drnet,validation,D1,TBI,regions,Third ventricle,ReferenceVolume,mm3,ok,68,90,90


,Variant,DatasetRole,Dataset,GroupBy,GroupValue,Head,Region,Metric,Unit,Animals,Scans,Mean,SD,Minimum,Maximum
0,3drnet,holdout,D1,Condition,TBI,brain_mask,Brain,ASSD,mm,112,112,0.089956,0.046937,0.044834,0.349878
1,3drnet,holdout,D1,Condition,TBI,brain_mask,Brain,AVE,mm3,112,112,21.229598,42.179166,0.056000,299.710000
2,3drnet,holdout,D1,Condition,TBI,brain_mask,Brain,Dice,fraction,112,112,0.968856,0.010322,0.926861,0.984376
3,3drnet,holdout,D1,Condition,TBI,brain_mask,Brain,HD95,mm,112,112,0.434384,0.509845,0.141419,3.600000
4,3drnet,holdout,D1,Condition,TBI,brain_mask,Brain,IoU,fraction,112,112,0.939784,0.019185,0.863691,0.969232
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
995,3drnet,validation,D1,Strain,unknown,regions,Third ventricle,Precision,fraction,68,68,0.705752,0.185697,0.174140,1.000000
996,3drnet,validation,D1,Strain,unknown,regions,Third ventricle,PredictionVolume,mm3,68,68,7.765831,24.847411,0.070000,181.032000
997,3drnet,validation,D1,Strain,unknown,regions,Third ventricle,RVE,%,68,68,9.677938,81.603072,-95.513495,397.067545
998,3drnet,validation,D1,Strain,unknown,regions,Third ventricle,ReferenceVolume,mm3,68,68,4.718691,8.886722,0.459000,37.110000


Additional anatomy, cohort, participant and structure-size tables are in the workbook.
Complete native patch and postprocessed volume tables: c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3drnet_kfold\RUN_20261015_130622_443191\summary
Workbook: c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3drnet_kfold\RUN_20261015_130622_443191\summary\evaluation_metrics.xlsx


## Explore outer holdout predictions against ground truth

Run the cell below after training/evaluation, or point `VIEW_RUN` at an existing matching run folder to inspect it without fitting. Saved full-volume `regions.nii.gz` files are loaded directly; no predictions are recomputed. This requires inference and prediction saving to have been enabled.

The table lists every available scan/timepoint and fold. The viewer initially loads up to three rows; set `VIEW_SCAN_INDICES=(0, 4)` to explore other rows. Use the Plotly dropdown to select a scan and reference-oriented plane, then drag the slice slider. Zoom/pan works in each MRI/GT/prediction panel.

Both overlays use the same class colors. The title lists unannotated GT regions: their absence is not evidence of a prediction error. Set `VIEW_REGION` to a foreground **original annotation ID** (for example 13 for the ipsilateral ventricle) to isolate one region. `VIEW_OPACITY` controls the overlay. Previews sample up to 64 slices per plane and 192 pixels per side; set `VIEW_MAX_SLICES=None` for every slice and raise `VIEW_MAX_PIXELS` for more detail. Saved masks are unchanged. The controls use native Plotly rendering.


In [9]:
from src.evaluation.inference import saved_prediction_manifest, prediction_comparison_figure

VIEW_RUN: Path | None = None  # Existing run folder, or use the result above.
VIEW_SCAN_INDICES: tuple[int, ...] | None = None  # None: first three manifest rows.
VIEW_REGION: int | None = None  # Original annotation ID (e.g. 13 = ipsi ventricle); None shows all.
VIEW_OPACITY: float = 0.55
VIEW_MAX_SLICES: int | None = 64
VIEW_MAX_PIXELS: int = 192
VIEW_ROLE: str = 'holdout'

viewer_role = VIEW_ROLE
viewer_run = VIEW_RUN
current_result = globals().get("result")
if viewer_run is None and current_result is not None:
    viewer_run = current_result.run_dir
if viewer_run is None and RESUME_RUN is not None:
    viewer_run = RESUME_RUN

if viewer_run is None:
    print("Train/evaluate first, or set VIEW_RUN to an existing run folder.")
else:
    prediction_views = saved_prediction_manifest(prepared, viewer_run, role=viewer_role)
    display(prediction_views)

    if prediction_views.empty:
        print("No saved predictions for this role. Check the run, VIEW_ROLE and prediction-saving settings.")
    else:
        prediction_figure = prediction_comparison_figure(
            data=prepared, predictions=prediction_views,
            scan_indices=VIEW_SCAN_INDICES, region=VIEW_REGION,
            opacity=VIEW_OPACITY, max_slices=VIEW_MAX_SLICES,
            max_pixels=VIEW_MAX_PIXELS,
        )
        prediction_figure.show(renderer="vscode")


,Subject,Scan,Group,Fold,DatasetRole,PredictionPath
ViewIndex,,,,,,
0,D1/SUBJ_0001,SUBJ_0001,D1_T1w,0,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
1,D1/SUBJ_0005,SUBJ_0005,D1_T1w,0,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
2,D1/SUBJ_0011,SUBJ_0011,D1_T1w,0,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
3,D1/SUBJ_0012,SUBJ_0012,D1_T1w,0,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
4,D1/SUBJ_0013,SUBJ_0013,D1_T1w,0,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
...,...,...,...,...,...,...
107,D1/SUBJ_0099,SUBJ_0099,D1_T2w,4,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
108,D1/SUBJ_0101,SUBJ_0101,D1_T2w,4,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...
109,D1/SUBJ_0103,SUBJ_0103,D1_T2w,4,holdout,c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3d...


## Evaluate the best checkpoint after stopping training

Interrupt training, then run this cell independently of `result`. Set `CHECKPOINT_RUN` to the existing **run folder**, select `CHECKPOINT_FOLD`, and enable `RUN_CHECKPOINT_EVALUATION`. After a kernel restart, only the repository setup cell and this cell are needed: the saved experiment supplies architecture, preprocessing, label policy and animal selection.

The default cohort matches this notebook. Fixed-split runs use test animals, CV uses outer holdouts, and historical rat CV uses validation animals. Every selected animal includes all timepoints. A best checkpoint must already exist; an unfinished epoch is not evaluated. The committed selected-weight copy is used when recovery state is available.

This measures native patches and performs full-volume inference, saves metrics/predictions to a fresh folder outside the training run, and opens the MRI/GT/prediction viewer. Training weights, optimizer, history and completion flags are left intact. Inference can take time; leave the switch False to skip it. Use notebook 09 to reopen an evaluation without recomputing predictions.

The common RARE reference is explicitly used for checkpoint evaluation, including older checkpoints. A model trained with a different orientation receives a changed input convention; those scores should be interpreted as evaluation with an orientation override. Training recovery files remain unchanged.


The independent cell exposes `checkpoint_postprocessing` and always restores original annotation IDs, including when the saved run predates these settings. It writes `prediction_labels.json`, so the viewer uses the exact exported IDs. `CHECKPOINT_REGION` selects an original annotation ID. Changing evaluation settings does not change training targets or weights.


In [10]:
from src.experiments.config import PostprocessingConfig
from src.evaluation.inference import (
    best_checkpoint_settings, evaluate_saved_model,
    saved_prediction_manifest, prediction_comparison_figure,
)

RUN_CHECKPOINT_EVALUATION: bool = False
CHECKPOINT_RUN: Path | None = None  # results/<model>/<run>; required after interruption/restart.
CHECKPOINT_FOLD: int = 0
CHECKPOINT_OUTPUT: Path | None = None  # None creates a fresh evaluation folder.
CHECKPOINT_SCAN_INDICES: tuple[int, ...] | None = None
CHECKPOINT_REGION: int | None = None
CHECKPOINT_MAX_SLICES: int | None = 64
CHECKPOINT_ROLE: str = 'holdout'

checkpoint_run = CHECKPOINT_RUN
current_result = globals().get("result")
if checkpoint_run is None and current_result is not None:
    checkpoint_run = current_result.run_dir
if checkpoint_run is None:
    checkpoint_run = globals().get("RESUME_RUN")

checkpoint_postprocessing = PostprocessingConfig(
    clean_brain_mask=True,
    fill_small_holes=True, holes_max_area=20000,
    remove_small_objects=True, object_min_area=30000,
    split_ventricles=True, use_centroids=True,
    default_hemisphere="right", lesion_voxels_threshold=10,
)

checkpoint_evaluation = None
if RUN_CHECKPOINT_EVALUATION:
    if checkpoint_run is None:
        raise ValueError("Set CHECKPOINT_RUN to the stopped run folder first")
    checkpoint_settings = best_checkpoint_settings(
        run_dir=checkpoint_run, fold=CHECKPOINT_FOLD, role=CHECKPOINT_ROLE,
        output_dir=CHECKPOINT_OUTPUT, reference=REFERENCE,
        original_label_ids=True, postprocessing=checkpoint_postprocessing,
        evaluate_patches=True,
    )
    print("Selected weights:", checkpoint_settings.model_file)
    checkpoint_evaluation = evaluate_saved_model(checkpoint_settings)
    print("Evaluation saved to:", checkpoint_evaluation.output_dir)
    display(checkpoint_evaluation.patch_metrics)
    print("Evaluation workbook:", checkpoint_evaluation.output_dir / "evaluation_metrics.xlsx")
    from src.evaluation.classification import classification_report, healthy_lesion_report
    checkpoint_classifier = classification_report(checkpoint_evaluation.classifier_predictions)
    if not checkpoint_classifier.summary.empty:
        display(checkpoint_classifier.summary)
        display(checkpoint_classifier.confusion)
    checkpoint_sham_animals, checkpoint_sham_summary = healthy_lesion_report(checkpoint_evaluation.metrics)
    if not checkpoint_sham_summary.empty:
        display(checkpoint_sham_summary)
    checkpoint_metrics = checkpoint_evaluation.metrics
    checkpoint_dice = checkpoint_metrics.loc[checkpoint_metrics["Metric"] == "Dice"]
    display(checkpoint_dice)
    from src.evaluation.reporting import evaluation_report

    checkpoint_report = evaluation_report(
        checkpoint_metrics, manifest=checkpoint_evaluation.manifest,
    )
    display(checkpoint_report.region_set_summary)
    display(checkpoint_report.region_coverage)
    display(checkpoint_report.subgroup_summary)
    display(checkpoint_report.participant_flow)
    checkpoint_views = saved_prediction_manifest(
        data=checkpoint_evaluation.data, run_dir=checkpoint_evaluation.output_dir,
        role=CHECKPOINT_ROLE,
    )
    display(checkpoint_views)
    checkpoint_figure = prediction_comparison_figure(
        data=checkpoint_evaluation.data, predictions=checkpoint_views,
        scan_indices=CHECKPOINT_SCAN_INDICES, region=CHECKPOINT_REGION,
        max_slices=CHECKPOINT_MAX_SLICES,
    )
    checkpoint_figure.show(renderer="vscode")
else:
    print("Set CHECKPOINT_RUN and RUN_CHECKPOINT_EVALUATION=True to evaluate saved best weights.")


Set CHECKPOINT_RUN and RUN_CHECKPOINT_EVALUATION=True to evaluate saved best weights.


## Paper tables: average test performance across folds

The main dataframe reports **mean of fold animal-means ± SD across folds**. Longitudinal scans are averaged within each animal first. A single-fold evaluation shows a mean without an invented zero fold SD. Seeds, datasets, SHAM/TBI and evaluation roles stay separate.

Set `PAPER_RESULTS_DIR` to an explicit completed run, study or checkpoint-evaluation folder to load it after a kernel restart. Otherwise the cell uses the current study/run, then a checkpoint evaluation. It reads saved CSVs and performs no fitting or inference. Review `fold_coverage` before copying a final table.

`paper_table` contains full-volume brain/region results. `paper_region_table` contains explicit region-set means; by default these require complete annotation for the selected set. Individual ROI rows still use all valid partial annotations. `Animals` counts Dice contributors, `BoundaryAnimals` counts defined boundary measurements, and the numerical `statistics` table contains every metric's denominator. Missing values stay missing.

`paper_animal_intervals` gives the separate animal mean with bootstrap confidence intervals. It is not an interval for the equal-fold estimator. Native patch measurements, classification/confusion, volume agreement, reference comparisons and recorded costs remain separate tables. Paired comparisons use the chosen reference and Holm adjustment over the returned test family. Classifier exact intervals pool disjoint holdouts only; repeated test/external predictions do not add animals.

Enable `EXPORT_PAPER_TABLES` to write CSVs and `paper_tables.xlsx` to a fresh folder. Full-precision numerical results, source hashes and aggregation settings are included. Patch losses retain their own objective definitions. This does not complete the deferred independent D4 manual-volume analysis.


In [11]:
from pathlib import Path
from IPython.display import display
from src.evaluation.paper_tables import PaperTableConfig, paper_tables_from_folder

PAPER_RESULTS_DIR: Path | None = None  # Explicit run, study or checkpoint-evaluation folder.
PAPER_ROLES: tuple[str, ...] = ("holdout", "test")
PAPER_REFERENCE_VARIANT: str | None = None  # None skips paired comparisons.
PAPER_BOOTSTRAP_SAMPLES: int = 2000
COMPLETE_REGION_SETS_ONLY: bool = True
EXPORT_PAPER_TABLES: bool = False
PAPER_OUTPUT_DIR: Path | None = None  # None: <selected folder>/paper_tables; must be fresh.

paper_folder = PAPER_RESULTS_DIR
if paper_folder is None:
    current_study = globals().get("study")
    current_result = globals().get("result")
    current_checkpoint = globals().get("checkpoint_evaluation")
    current_evaluation = globals().get("evaluation")
    if current_study is not None:
        paper_folder = current_study.study_dir
    elif current_result is not None:
        paper_folder = current_result.run_dir
    elif current_checkpoint is not None:
        paper_folder = current_checkpoint.output_dir
    elif current_evaluation is not None and hasattr(current_evaluation, "output_dir"):
        paper_folder = current_evaluation.output_dir

paper_tables = None
paper_table = None
paper_region_table = None
paper_animal_intervals = None
if paper_folder is None:
    print("Finish evaluation or set PAPER_RESULTS_DIR to saved results; no training is required.")
else:
    paper_settings = PaperTableConfig(
        roles=PAPER_ROLES, reference_variant=PAPER_REFERENCE_VARIANT,
        complete_region_sets_only=COMPLETE_REGION_SETS_ONLY,
        bootstrap_samples=PAPER_BOOTSTRAP_SAMPLES, confidence=0.95, seed=42, decimals=3,
    )
    print("Paper-table source:", paper_folder)
    paper_tables = paper_tables_from_folder(paper_folder, settings=paper_settings)
    paper_table = paper_tables.segmentation
    paper_region_table = paper_tables.region_sets
    paper_animal_intervals = paper_tables.animal_intervals
    display(paper_tables.fold_coverage)
    display(paper_table)
    display(paper_region_table)
    display(paper_animal_intervals)
    display(paper_tables.patches)
    display(paper_tables.classification)
    display(paper_tables.confusion)
    display(paper_tables.agreement)
    display(paper_tables.comparisons)
    display(paper_tables.healthy_lesion)
    display(paper_tables.costs)

if EXPORT_PAPER_TABLES:
    if paper_tables is None:
        raise ValueError("Build the paper tables before exporting")
    paper_output = PAPER_OUTPUT_DIR
    if paper_output is None:
        paper_output = Path(paper_folder) / "paper_tables"
    saved_paper_tables = paper_tables.export(paper_output)
    print("Paper tables saved to:", saved_paper_tables)


Paper-table source: c:\Users\MDesalvo\Desktop\RNET3D\results\d1_3drnet_kfold\RUN_20261015_130622_443191


,Variant,Seed,DatasetRole,ObservedFolds,ObservedAnimals,ExpectedFolds,Complete
0,3drnet,42,holdout,5,112,5,True


,Variant,Seed,DatasetRole,Dataset,Condition,Head,Region,Folds,ObservedAnimals,Animals,...,Dice,HD95 (mm),ASSD (mm),AVE (mm3),RVE (%),Sensitivity,Precision,IoU,ReferenceVolume (mm3),PredictionVolume (mm3)
0,3drnet,42,holdout,D1,TBI,brain_mask,Brain,5,112,112,...,0.969 ± 0.005,0.438 ± 0.260,0.090 ± 0.024,21.374 ± 10.915,-0.175 ± 2.336,0.968 ± 0.016,0.970 ± 0.008,0.940 ± 0.010,735.512 ± 190.899,739.732 ± 193.358
1,3drnet,42,holdout,D1,TBI,regions,Contra ventricle,5,112,112,...,0.459 ± 0.131,3.371 ± 1.403,0.929 ± 0.582,3.143 ± 1.664,-50.917 ± 26.175,0.373 ± 0.171,0.733 ± 0.116,0.326 ± 0.119,5.329 ± 2.618,2.362 ± 1.349
2,3drnet,42,holdout,D1,TBI,regions,Ipsi ventricle,5,112,112,...,0.328 ± 0.085,3.819 ± 1.962,0.895 ± 0.507,2.188 ± 2.298,-11.942 ± 54.478,0.295 ± 0.127,0.620 ± 0.199,0.219 ± 0.070,2.446 ± 1.081,3.322 ± 2.994
3,3drnet,42,holdout,D1,TBI,regions,Lesion,5,112,112,...,0.775 ± 0.019,4.683 ± 2.447,0.541 ± 0.276,6.854 ± 3.248,6.004 ± 14.739,0.800 ± 0.055,0.778 ± 0.051,0.644 ± 0.024,29.648 ± 7.681,30.902 ± 10.045
4,3drnet,42,holdout,D1,TBI,regions,Third ventricle,5,112,112,...,0.614 ± 0.057,2.806 ± 2.209,0.348 ± 0.232,3.088 ± 2.774,23.914 ± 87.383,0.643 ± 0.165,0.695 ± 0.190,0.460 ± 0.052,3.851 ± 1.672,4.987 ± 3.862


,Variant,Seed,DatasetRole,Dataset,Condition,Head,Region,Folds,ObservedAnimals,Animals,DiceFolds,BoundaryAnimals,Dice,HD95 (mm),ASSD (mm),AVE (mm3),RVE (%),Sensitivity,Precision,IoU
0,3drnet,42,holdout,D1,TBI,region_set,all_roi,5,112,112,5,112,0.544 ± 0.064,3.645 ± 1.732,0.667 ± 0.319,3.818 ± 1.801,-8.273 ± 37.176,0.529 ± 0.109,0.707 ± 0.128,0.412 ± 0.059
1,3drnet,42,holdout,D1,TBI,region_set,all_roi_and_brain,5,112,112,5,112,0.629 ± 0.052,2.999 ± 1.399,0.551 ± 0.257,7.329 ± 3.363,-6.660 ± 29.994,0.617 ± 0.089,0.761 ± 0.102,0.518 ± 0.048
2,3drnet,42,holdout,D1,TBI,region_set,anatomy_and_brain,5,112,112,5,112,0.592 ± 0.061,2.581 ± 1.170,0.554 ± 0.269,7.448 ± 3.465,-9.844 ± 36.797,0.571 ± 0.105,0.756 ± 0.124,0.486 ± 0.055
3,3drnet,42,holdout,D1,TBI,region_set,anatomy_only,5,112,112,5,112,0.467 ± 0.080,3.307 ± 1.549,0.710 ± 0.357,2.806 ± 1.507,-13.060 ± 48.671,0.438 ± 0.138,0.683 ± 0.168,0.335 ± 0.072


,Variant,Seed,DatasetRole,Dataset,Condition,Head,Region,Folds,ObservedAnimals,Animals,...,Dice,HD95 (mm),ASSD (mm),AVE (mm3),RVE (%),Sensitivity,Precision,IoU,ReferenceVolume (mm3),PredictionVolume (mm3)
0,3drnet,42,holdout,D1,TBI,brain_mask,Brain,5,112,112,...,"0.969 [0.967, 0.971]","0.434 [0.349, 0.534]","0.090 [0.082, 0.099]","21.230 [14.138, 30.492]","-0.151 [-0.703, 0.435]","0.968 [0.964, 0.972]","0.970 [0.967, 0.973]","0.940 [0.936, 0.943]","733.629 [567.770, 933.374]","737.947 [569.341, 942.641]"
1,3drnet,42,holdout,D1,TBI,region_set,all_roi,5,112,112,...,"0.545 [0.520, 0.569]","3.620 [2.454, 5.061]","0.661 [0.474, 0.883]","3.793 [2.443, 5.508]","-8.331 [-17.879, 2.054]","0.529 [0.504, 0.557]","0.708 [0.673, 0.739]","0.413 [0.391, 0.435]",NaN,NaN
2,3drnet,42,holdout,D1,TBI,region_set,all_roi_and_brain,5,112,112,...,"0.629 [0.609, 0.649]","2.979 [2.034, 4.151]","0.546 [0.395, 0.724]","7.281 [4.871, 10.449]","-6.702 [-14.346, 1.625]","0.617 [0.597, 0.640]","0.761 [0.733, 0.787]","0.518 [0.500, 0.536]",NaN,NaN
3,3drnet,42,holdout,D1,TBI,region_set,anatomy_and_brain,5,112,112,...,"0.593 [0.570, 0.616]","2.564 [1.846, 3.437]","0.549 [0.398, 0.724]","7.396 [4.781, 10.829]","-9.892 [-19.537, 0.736]","0.571 [0.548, 0.598]","0.757 [0.723, 0.788]","0.487 [0.467, 0.507]",NaN,NaN
4,3drnet,42,holdout,D1,TBI,region_set,anatomy_only,5,112,112,...,"0.468 [0.437, 0.498]","3.286 [2.339, 4.423]","0.704 [0.504, 0.935]","2.785 [1.458, 4.516]","-13.133 [-25.933, 1.132]","0.439 [0.408, 0.473]","0.683 [0.638, 0.725]","0.336 [0.310, 0.362]",NaN,NaN
5,3drnet,42,holdout,D1,TBI,regions,Contra ventricle,5,112,112,...,"0.461 [0.416, 0.504]","3.331 [2.177, 4.750]","0.905 [0.542, 1.353]","3.117 [1.662, 5.030]","-50.623 [-56.525, -44.133]","0.376 [0.331, 0.422]","0.736 [0.685, 0.785]","0.328 [0.291, 0.364]","5.298 [3.164, 7.891]","2.361 [1.161, 4.078]"
6,3drnet,42,holdout,D1,TBI,regions,Ipsi ventricle,5,112,112,...,"0.328 [0.291, 0.370]","3.781 [2.815, 4.978]","0.882 [0.655, 1.142]","2.174 [0.774, 3.994]","-12.447 [-36.287, 15.599]","0.295 [0.251, 0.339]","0.627 [0.563, 0.689]","0.220 [0.189, 0.256]","2.428 [1.379, 3.769]","3.296 [1.299, 5.867]"
7,3drnet,42,holdout,D1,TBI,regions,Lesion,5,112,112,...,"0.775 [0.755, 0.793]","4.650 [2.746, 7.058]","0.536 [0.345, 0.775]","6.819 [4.981, 9.166]","5.988 [0.726, 11.312]","0.800 [0.771, 0.824]","0.778 [0.755, 0.800]","0.644 [0.621, 0.666]","29.599 [23.292, 37.285]","30.817 [24.042, 39.149]"
8,3drnet,42,holdout,D1,TBI,regions,Third ventricle,5,112,112,...,"0.614 [0.585, 0.643]","2.785 [1.710, 4.188]","0.346 [0.237, 0.482]","3.062 [1.386, 5.852]","23.499 [2.581, 48.041]","0.643 [0.604, 0.681]","0.696 [0.656, 0.734]","0.460 [0.431, 0.488]","3.833 [2.555, 5.431]","4.963 [2.655, 8.467]"


...

""


,Variant,Seed,DatasetRole,Dataset,Condition,Head,Region,n,Status,unit,...,variance_sensitivity,proportional_bias_note,wilcoxon_statistic,wilcoxon_pvalue,levene_statistic,levene_pvalue,proportional_slope_pvalue,proportional_intercept,difference_shapiro_statistic,difference_shapiro_pvalue
0,3drnet,42,holdout,D1,TBI,brain_mask,Brain,112,ok,mm3,...,paired-subject percentile bootstrap of SD redu...,"OLS difference versus pair mean; diagnostic, n...",3148.0,9.629516e-01,0.000849,0.976778,4.806898e-08,-13.248851,0.594722,4.224966e-16
1,3drnet,42,holdout,D1,TBI,regions,Contra ventricle,112,ok,mm3,...,paired-subject percentile bootstrap of SD redu...,"OLS difference versus pair mean; diagnostic, n...",248.0,2.550120e-17,2.422489,0.121029,1.894603e-11,-0.723085,0.331597,2.494317e-20
2,3drnet,42,holdout,D1,TBI,regions,Ipsi ventricle,112,ok,mm3,...,paired-subject percentile bootstrap of SD redu...,"OLS difference versus pair mean; diagnostic, n...",1445.0,9.931199e-07,0.911630,0.340721,1.367441e-16,-1.120750,0.246070,1.992085e-21
3,3drnet,42,holdout,D1,TBI,regions,Lesion,112,ok,mm3,...,paired-subject percentile bootstrap of SD redu...,"OLS difference versus pair mean; diagnostic, n...",2839.0,3.454168e-01,0.019877,0.888009,7.582056e-03,-1.435177,0.689640,4.600489e-14
4,3drnet,42,holdout,D1,TBI,regions,Third ventricle,112,ok,mm3,...,paired-subject percentile bootstrap of SD redu...,"OLS difference versus pair mean; diagnostic, n...",2969.5,5.723060e-01,0.708593,0.400817,1.190541e-20,-2.816875,0.233201,1.388436e-21


""


""


,Variant,Kind,DatasetRole,Dataset,Device,Precision,ProvenanceStatus,Metric,Unit,Recorded,Rows,Mean,Median,Minimum,Maximum
0,3drnet,training,training,unknown,"/physical_device:CPU:0, /physical_device:GPU:0",unknown,missing_hardware_metadata,best_epoch,count,5,5,8.400000e+00,9.000000e+00,7.000000e+00,9.000000e+00
1,3drnet,training,training,unknown,"/physical_device:CPU:0, /physical_device:GPU:0",unknown,missing_hardware_metadata,epochs_completed,count,5,5,1.000000e+01,1.000000e+01,1.000000e+01,1.000000e+01
2,3drnet,training,training,unknown,"/physical_device:CPU:0, /physical_device:GPU:0",unknown,missing_hardware_metadata,evaluation_seconds,s,5,5,6.933462e+02,7.227204e+02,4.737812e+02,8.552550e+02
3,3drnet,training,training,unknown,"/physical_device:CPU:0, /physical_device:GPU:0",unknown,missing_hardware_metadata,parameter_count,count,5,5,7.173518e+06,7.173518e+06,7.173518e+06,7.173518e+06
4,3drnet,training,training,unknown,"/physical_device:CPU:0, /physical_device:GPU:0",unknown,missing_hardware_metadata,training_seconds,s,5,5,2.951627e+03,2.996132e+03,2.775979e+03,3.112676e+03
